In [2]:
from qdrant_client import QdrantClient
from qdrant_client.models import Distance, VectorParams, PointStruct

import pandas as pd
from google import genai
import openai


/Users/kishorkumarparoi/Desktop/Maven - The AI Engineering Bootcamp /Resources/AIE5-main/24_Langgraph/.venv/lib/python3.12/site-packages/tqdm/auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm


In [3]:
df = pd.read_json('../../../data/Data_With_Images.jsonl', lines=True)
print(df.head())

               main_category  \
0            All Electronics   
1            All Electronics   
2                  Computers   
3             AMAZON FASHION   
4  Cell Phones & Accessories   

                                               title  average_rating  \
0             FS-1051 FATSHARK TELEPORTER V3 HEADSET             3.5   
1                      Ce-H22B12-S1 4Kx2K Hdmi 4Port             5.0   
2  Digi-Tatoo Decal Skin Compatible With MacBook ...             4.5   
3  NotoCity Compatible with Vivoactive 4 band 22m...             4.5   
4             Motorola Droid X Essentials Combo Pack             3.8   

   rating_number                                           features  \
0              6                                                 []   
1              1             [UPC: 662774021904, Weight: 0.600 lbs]   
2            246  [WARNING: Please IDENTIFY MODEL NUMBER on the ...   
3            233  [☛NotoCity 22mm band is designed for Vivoactiv...   
4             64  [

In [4]:
df.info()

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 2026 entries, 0 to 2025
Data columns (total 14 columns):
 #   Column          Non-Null Count  Dtype  
---  ------          --------------  -----  
 0   main_category   2000 non-null   object 
 1   title           2026 non-null   object 
 2   average_rating  2026 non-null   float64
 3   rating_number   2026 non-null   int64  
 4   features        2026 non-null   object 
 5   description     2026 non-null   object 
 6   price           2026 non-null   float64
 7   images          2026 non-null   object 
 8   videos          2026 non-null   object 
 9   store           2026 non-null   object 
 10  categories      2026 non-null   object 
 11  details         2026 non-null   object 
 12  parent_asin     2026 non-null   object 
 13  product_id      2026 non-null   object 
dtypes: float64(2), int64(1), object(11)
memory usage: 221.7+ KB


In [5]:
# df = df.drop(columns=['bought_together', 'subtitle','author'])

In [6]:
df.info()

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 2026 entries, 0 to 2025
Data columns (total 14 columns):
 #   Column          Non-Null Count  Dtype  
---  ------          --------------  -----  
 0   main_category   2000 non-null   object 
 1   title           2026 non-null   object 
 2   average_rating  2026 non-null   float64
 3   rating_number   2026 non-null   int64  
 4   features        2026 non-null   object 
 5   description     2026 non-null   object 
 6   price           2026 non-null   float64
 7   images          2026 non-null   object 
 8   videos          2026 non-null   object 
 9   store           2026 non-null   object 
 10  categories      2026 non-null   object 
 11  details         2026 non-null   object 
 12  parent_asin     2026 non-null   object 
 13  product_id      2026 non-null   object 
dtypes: float64(2), int64(1), object(11)
memory usage: 221.7+ KB


In [7]:
df['price'] = df['price'].fillna(df['price'].mean())

In [8]:
df.info()

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 2026 entries, 0 to 2025
Data columns (total 14 columns):
 #   Column          Non-Null Count  Dtype  
---  ------          --------------  -----  
 0   main_category   2000 non-null   object 
 1   title           2026 non-null   object 
 2   average_rating  2026 non-null   float64
 3   rating_number   2026 non-null   int64  
 4   features        2026 non-null   object 
 5   description     2026 non-null   object 
 6   price           2026 non-null   float64
 7   images          2026 non-null   object 
 8   videos          2026 non-null   object 
 9   store           2026 non-null   object 
 10  categories      2026 non-null   object 
 11  details         2026 non-null   object 
 12  parent_asin     2026 non-null   object 
 13  product_id      2026 non-null   object 
dtypes: float64(2), int64(1), object(11)
memory usage: 221.7+ KB


In [9]:
df['store'] = df['store'].fillna(df['store'].mode()[0])

In [10]:
df.isnull().sum()

main_category     26
title              0
average_rating     0
rating_number      0
features           0
description        0
price              0
images             0
videos             0
store              0
categories         0
details            0
parent_asin        0
product_id         0
dtype: int64

In [11]:
df.info()

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 2026 entries, 0 to 2025
Data columns (total 14 columns):
 #   Column          Non-Null Count  Dtype  
---  ------          --------------  -----  
 0   main_category   2000 non-null   object 
 1   title           2026 non-null   object 
 2   average_rating  2026 non-null   float64
 3   rating_number   2026 non-null   int64  
 4   features        2026 non-null   object 
 5   description     2026 non-null   object 
 6   price           2026 non-null   float64
 7   images          2026 non-null   object 
 8   videos          2026 non-null   object 
 9   store           2026 non-null   object 
 10  categories      2026 non-null   object 
 11  details         2026 non-null   object 
 12  parent_asin     2026 non-null   object 
 13  product_id      2026 non-null   object 
dtypes: float64(2), int64(1), object(11)
memory usage: 221.7+ KB


In [12]:
df.isna().sum()[df.isna().sum() > 0]

main_category    26
dtype: int64

In [13]:
# import uuid

# # Add to your DataFrame
# df['product_id'] = [str(uuid.uuid4()) for _ in range(len(df))]

In [14]:
# # Read it back to confirm
# df_verify = pd.read_json('../../../data/Data_With_Images.jsonl', lines=True)
# df_verify.head()
# print("Before Columns:", df_verify.columns.tolist())
# # Save the updated DataFrame
# df.to_json('../../../data/Data_With_Images.jsonl', orient='records', lines=True)
# print("After Columns:", df.columns.tolist())

In [15]:
len(df)

2026

In [16]:
def preprocess_review(review):
    return {
        'product_id': review['product_id'], 
        'main_category': review['main_category'],
        'title': review['title'],
        'average_rating': review['average_rating'],
        'rating_number': review['rating_number'],
        'features': review['features'],
        'description': review['description'],
        'price': review['price'],
        'images': review['images'],
        'videos': review['videos'],
        'store': review['store'],
        'categories': review['categories'],
        'details': review['details'],
        'parent_asin': review['parent_asin'],
    }

In [17]:
df.head()

,main_category,title,average_rating,rating_number,features,description,price,images,videos,store,categories,details,parent_asin,product_id
0,All Electronics,FS-1051 FATSHARK TELEPORTER V3 HEADSET,3.5,6,[],[Teleporter V3 The “Teleporter V3” kit sets a ...,96.551146,[{'thumb': 'https://m.media-amazon.com/images/...,[],Fat Shark,"[Electronics, Television & Video, Video Glasses]","{'Date First Available': 'August 2, 2014', 'Ma...",B00MCW7G9M,b86c3534-084b-449b-889e-50bd268ff964
1,All Electronics,Ce-H22B12-S1 4Kx2K Hdmi 4Port,5.0,1,"[UPC: 662774021904, Weight: 0.600 lbs]",[HDMI In - HDMI Out],96.551146,[{'thumb': 'https://m.media-amazon.com/images/...,[],SIIG,"[Electronics, Television & Video, Accessories,...",{'Product Dimensions': '0.83 x 4.17 x 2.05 inc...,B00YT6XQSE,945a8ca0-282f-424a-83db-646304822e23
2,Computers,Digi-Tatoo Decal Skin Compatible With MacBook ...,4.5,246,[WARNING: Please IDENTIFY MODEL NUMBER on the ...,[],19.990000,[{'thumb': 'https://m.media-amazon.com/images/...,"[{'title': 'AL 2Sides Video', 'url': 'https://...",Digi-Tatoo,"[Electronics, Computers & Accessories, Laptop ...","{'Brand': 'Digi-Tatoo', 'Color': 'Fresh Marble...",B07SM135LS,c67b6305-54b3-4a14-816a-532c3d2a108c
3,AMAZON FASHION,NotoCity Compatible with Vivoactive 4 band 22m...,4.5,233,[☛NotoCity 22mm band is designed for Vivoactiv...,[],9.990000,[{'thumb': 'https://m.media-amazon.com/images/...,[],NotoCity,"[Electronics, Wearable Technology, Clips, Arm ...","{'Date First Available': 'May 29, 2020', 'Manu...",B089CNGZCW,5f511624-c19c-401e-8669-2d22afaa50dc
4,Cell Phones & Accessories,Motorola Droid X Essentials Combo Pack,3.8,64,"[New Droid X Essentials Combo Pack, Exclusive ...",[all Genuine High Quality Motorola Made Access...,14.990000,[{'thumb': 'https://m.media-amazon.com/images/...,[],Verizon,"[Electronics, Computers & Accessories, Compute...",{'Product Dimensions': '11.6 x 6.9 x 3.1 inche...,B004E2Z88O,8b781665-d968-4aaf-ac18-f7e353de0de9


In [18]:
data_to_embed = df.apply(preprocess_review, axis=1).tolist()

Define the embedding function

In [19]:
import os
from dotenv import load_dotenv

# Load environment variables from .env file
load_dotenv()

# Retrieve API keys from environment variables
openai_api_key = os.getenv('OPENAI_API_KEY')
google_api_key = os.getenv('GEMINI_API_KEY')
qdrant_url = os.getenv('QDRANT_URL')
qdrant_api_key = os.getenv('QDRANT_API_KEY')

# Verify keys are loaded
print(f"OpenAI API Key present: {bool(openai_api_key)}")
print(f"Google API Key present: {bool(google_api_key)}")
print(f"Qdrant URL present: {bool(qdrant_url)}")
print(f"Qdrant API Key present: {bool(qdrant_api_key)}")

OpenAI API Key present: True
Google API Key present: False
Qdrant URL present: True
Qdrant API Key present: False


In [20]:
response = openai.embeddings.create(
    input = "Random Text",
    model = "text-embedding-3-small"
)

In [21]:
len(response.data[0].embedding)

1536

In [22]:
def get_embedding(text):
    response = openai.embeddings.create(
        input = text,
        model = "text-embedding-3-small"
    )
    return response.data[0].embedding

In [23]:
get_embedding("This is a sample review text to test the embedding function.")

[0.01065826416015625,
 0.033905029296875,
 0.0261383056640625,
 -0.0107269287109375,
 -0.01123046875,
 -0.0386962890625,
 0.036773681640625,
 0.0222930908203125,
 0.00444793701171875,
 0.006702423095703125,
 0.0426025390625,
 -0.024810791015625,
 -0.03131103515625,
 -0.00766754150390625,
 0.01290130615234375,
 0.0243072509765625,
 0.00864410400390625,
 0.01479339599609375,
 0.017852783203125,
 0.0257415771484375,
 0.0228118896484375,
 -0.0273590087890625,
 -0.0175018310546875,
 0.050262451171875,
 -0.01277923583984375,
 -0.0440673828125,
 0.00849151611328125,
 0.041900634765625,
 0.051025390625,
 -0.048309326171875,
 0.034423828125,
 -0.03961181640625,
 0.019775390625,
 -0.0172119140625,
 -0.04534912109375,
 0.045684814453125,
 0.01219940185546875,
 0.01389312744140625,
 -0.00614166259765625,
 0.0256500244140625,
 0.0014276504516601562,
 0.0222625732421875,
 -0.01371002197265625,
 0.0169830322265625,
 -0.033050537109375,
 0.044464111328125,
 -0.01323699951171875,
 -0.029144287109375,
 

Estimate embedding time for `text-embedding-3-small`

In [24]:
df.info()

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 2026 entries, 0 to 2025
Data columns (total 14 columns):
 #   Column          Non-Null Count  Dtype  
---  ------          --------------  -----  
 0   main_category   2000 non-null   object 
 1   title           2026 non-null   object 
 2   average_rating  2026 non-null   float64
 3   rating_number   2026 non-null   int64  
 4   features        2026 non-null   object 
 5   description     2026 non-null   object 
 6   price           2026 non-null   float64
 7   images          2026 non-null   object 
 8   videos          2026 non-null   object 
 9   store           2026 non-null   object 
 10  categories      2026 non-null   object 
 11  details         2026 non-null   object 
 12  parent_asin     2026 non-null   object 
 13  product_id      2026 non-null   object 
dtypes: float64(2), int64(1), object(11)
memory usage: 221.7+ KB


In [25]:
import pandas as pd
import time

sample_text = data_to_embed[0]['title']

def benchmark_single_embedding(text, runs=3):
    durations = []
    for _ in range(runs):
        start = time.perf_counter()
        get_embedding(text)
        durations.append(time.perf_counter() - start)
    return sum(durations) / len(durations)

avg_seconds_per_record = benchmark_single_embedding(sample_text, runs=3)
records = [10, 100, 1000, 10000]

embedding_timing = pd.DataFrame({
    'records': records,
    'estimated_seconds': [avg_seconds_per_record * count for count in records],
})
embedding_timing['estimated_minutes'] = embedding_timing['estimated_seconds'] / 60
embedding_timing['estimated_hours'] = embedding_timing['estimated_minutes'] / 60
embedding_timing

,records,estimated_seconds,estimated_minutes,estimated_hours
0,10,5.295016,0.088250,0.001471
1,100,52.950163,0.882503,0.014708
2,1000,529.501625,8.825027,0.147084
3,10000,5295.016253,88.250271,1.470838


Create Qdrant Collection

In [26]:
qdrant_client = QdrantClient(url='http://localhost:6333')

In [29]:
qdrant_client.create_collection(
    collection_name="Amazon_Electronics_Products",
    vectors_config=VectorParams(size=1536, distance=Distance.COSINE)
)

True

Embed Data

In [30]:
pointstructs = PointStruct(
    id=0,
    vector=get_embedding("This is a sample review text to test the embedding function."),
    payload={
        'text': 'This is a sample review text to test the embedding function.',
        "model": "text-embedding-3-small" 
    }
)

In [31]:
pointstructs

PointStruct(id=0, vector=[0.01065826416015625, 0.033905029296875, 0.0261383056640625, -0.0107269287109375, -0.01123046875, -0.0386962890625, 0.036773681640625, 0.0222930908203125, 0.00444793701171875, 0.006702423095703125, 0.0426025390625, -0.024810791015625, -0.03131103515625, -0.00766754150390625, 0.01290130615234375, 0.0243072509765625, 0.00864410400390625, 0.01479339599609375, 0.017852783203125, 0.0257415771484375, 0.0228118896484375, -0.0273590087890625, -0.0175018310546875, 0.050262451171875, -0.01277923583984375, -0.0440673828125, 0.00849151611328125, 0.041900634765625, 0.051025390625, -0.048309326171875, 0.034423828125, -0.03961181640625, 0.019775390625, -0.0172119140625, -0.04534912109375, 0.045684814453125, 0.01219940185546875, 0.01389312744140625, -0.00614166259765625, 0.0256500244140625, 0.0014276504516601562, 0.0222625732421875, -0.01371002197265625, 0.0169830322265625, -0.033050537109375, 0.044464111328125, -0.01323699951171875, -0.029144287109375, -0.00920867919921875, 0

In [32]:
df.head()

,main_category,title,average_rating,rating_number,features,description,price,images,videos,store,categories,details,parent_asin,product_id
0,All Electronics,FS-1051 FATSHARK TELEPORTER V3 HEADSET,3.5,6,[],[Teleporter V3 The “Teleporter V3” kit sets a ...,96.551146,[{'thumb': 'https://m.media-amazon.com/images/...,[],Fat Shark,"[Electronics, Television & Video, Video Glasses]","{'Date First Available': 'August 2, 2014', 'Ma...",B00MCW7G9M,b86c3534-084b-449b-889e-50bd268ff964
1,All Electronics,Ce-H22B12-S1 4Kx2K Hdmi 4Port,5.0,1,"[UPC: 662774021904, Weight: 0.600 lbs]",[HDMI In - HDMI Out],96.551146,[{'thumb': 'https://m.media-amazon.com/images/...,[],SIIG,"[Electronics, Television & Video, Accessories,...",{'Product Dimensions': '0.83 x 4.17 x 2.05 inc...,B00YT6XQSE,945a8ca0-282f-424a-83db-646304822e23
2,Computers,Digi-Tatoo Decal Skin Compatible With MacBook ...,4.5,246,[WARNING: Please IDENTIFY MODEL NUMBER on the ...,[],19.990000,[{'thumb': 'https://m.media-amazon.com/images/...,"[{'title': 'AL 2Sides Video', 'url': 'https://...",Digi-Tatoo,"[Electronics, Computers & Accessories, Laptop ...","{'Brand': 'Digi-Tatoo', 'Color': 'Fresh Marble...",B07SM135LS,c67b6305-54b3-4a14-816a-532c3d2a108c
3,AMAZON FASHION,NotoCity Compatible with Vivoactive 4 band 22m...,4.5,233,[☛NotoCity 22mm band is designed for Vivoactiv...,[],9.990000,[{'thumb': 'https://m.media-amazon.com/images/...,[],NotoCity,"[Electronics, Wearable Technology, Clips, Arm ...","{'Date First Available': 'May 29, 2020', 'Manu...",B089CNGZCW,5f511624-c19c-401e-8669-2d22afaa50dc
4,Cell Phones & Accessories,Motorola Droid X Essentials Combo Pack,3.8,64,"[New Droid X Essentials Combo Pack, Exclusive ...",[all Genuine High Quality Motorola Made Access...,14.990000,[{'thumb': 'https://m.media-amazon.com/images/...,[],Verizon,"[Electronics, Computers & Accessories, Compute...",{'Product Dimensions': '11.6 x 6.9 x 3.1 inche...,B004E2Z88O,8b781665-d968-4aaf-ac18-f7e353de0de9


Write embedded data to qdrant

In [33]:
pointstructs = []
for idx, review in enumerate(data_to_embed):
    embedding = get_embedding(review['title'])
    pointstructs.append(PointStruct(
        id=idx,
        vector=embedding,
        payload={
            'product_id': review['product_id'],
            'text': review['title'],
            'description': review['description'],
            'images': review['images'],
            'videos': review['videos'],
            'price': review['price'],
            'rating_number': review['rating_number'],
            'main_category': review['main_category'],
            'categories': review['categories'],
            'store': review['store'],
            'details': review['details'],
            'features': review['features'],
        }
    ))

In [34]:
pointstructs

[PointStruct(id=0, vector=[-0.0206756591796875, -0.04010009765625, 0.0303192138671875, -0.0390625, -0.0233917236328125, -0.040863037109375, 0.0281219482421875, 0.03973388671875, 0.0386962890625, -0.033782958984375, 0.0204010009765625, 0.007526397705078125, -0.012939453125, 0.025115966796875, -0.01149749755859375, -0.055206298828125, -0.0021152496337890625, -0.0194244384765625, -0.0203857421875, 0.0135650634765625, 0.037017822265625, 0.0232391357421875, -0.00589752197265625, 0.00713348388671875, -0.01401519775390625, -0.051116943359375, 0.03125, -0.0153045654296875, 0.024444580078125, 0.0099334716796875, 0.012908935546875, -0.038177490234375, 0.035858154296875, -0.0132904052734375, -0.042633056640625, -0.002452850341796875, -0.0005397796630859375, 0.00478363037109375, -0.0291900634765625, -0.01226806640625, 0.04412841796875, 0.0018873214721679688, 0.0167083740234375, 0.04913330078125, 0.017974853515625, -0.023101806640625, 0.0215911865234375, 0.0323486328125, -0.0182342529296875, 0.0121

In [35]:
len(pointstructs)

2026

In [36]:
batch_size = 128

for start in range(0, len(pointstructs), batch_size):
    batch = pointstructs[start:start + batch_size]
    qdrant_client.upsert(
        collection_name="Amazon_Electronics_Products",
        wait=True,
        points=batch,
    )

print(f"Upserted {len(pointstructs)} points in batches of {batch_size}.")

Upserted 2026 points in batches of 128.


Define a function for data retrieval

In [37]:
def retrieve_data(query,k=5):
    query_embedding = get_embedding(query)
    results = qdrant_client.query_points(
        collection_name="Amazon_Electronics_Products",
        query=query_embedding,
        limit=k
    )
    return results

In [38]:
retrieve_data('What kind of Laptop do you offer?', k=10).points

[ScoredPoint(id=531, version=5, score=0.45798373, payload={'product_id': '696a0f42-9993-429c-b281-71054dac2a6d', 'text': "Acer Aspire 3 Laptop, 17.3'' HD+ 1600 x 900, 3.60GHz Intel Core i5-1035G, 20GB DDR4 RAM, 128GB SSD + 1TB HDD, DVD-Writer, Windows 10, A317-52", 'description': ["Acer Aspire 3 Laptop, 17.3'' HD+ 1600 x 900, 3.60GHz Intel Core i5-1035G, 20GB DDR4 RAM, 128GB SSD + 1TB HDD, DVD-Writer, Windows 10, A317-52"], 'images': [{'thumb': 'https://m.media-amazon.com/images/I/41-Dz1OBLfS._AC_US40_.jpg', 'large': 'https://m.media-amazon.com/images/I/41-Dz1OBLfS._AC_.jpg', 'variant': 'MAIN', 'hi_res': 'https://m.media-amazon.com/images/I/71o9WGV4E1S._AC_SL1500_.jpg'}, {'thumb': 'https://m.media-amazon.com/images/I/21LRZoGYbSS._AC_US40_.jpg', 'large': 'https://m.media-amazon.com/images/I/21LRZoGYbSS._AC_.jpg', 'variant': 'PT01', 'hi_res': 'https://m.media-amazon.com/images/I/61apF7DHVvS._AC_SL1500_.jpg'}, {'thumb': 'https://m.media-amazon.com/images/I/31aEorIsp0S._AC_US40_.jpg', 'lar

In [39]:
df.info()

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 2026 entries, 0 to 2025
Data columns (total 14 columns):
 #   Column          Non-Null Count  Dtype  
---  ------          --------------  -----  
 0   main_category   2000 non-null   object 
 1   title           2026 non-null   object 
 2   average_rating  2026 non-null   float64
 3   rating_number   2026 non-null   int64  
 4   features        2026 non-null   object 
 5   description     2026 non-null   object 
 6   price           2026 non-null   float64
 7   images          2026 non-null   object 
 8   videos          2026 non-null   object 
 9   store           2026 non-null   object 
 10  categories      2026 non-null   object 
 11  details         2026 non-null   object 
 12  parent_asin     2026 non-null   object 
 13  product_id      2026 non-null   object 
dtypes: float64(2), int64(1), object(11)
memory usage: 221.7+ KB
